# 09 — Tuning Familiar / Bridge / Adventurous by ear

Feedback from listening to notebook 08's tiers: Familiar is great, Bridge
sounds too close to Familiar, and Adventurous isn't far enough. The measured
cause of both: `tiers_for()`'s Bridge pool started scanning from rank 1 again
(so it could grab something as close as rank 2 if it merely lacked genre
overlap — no distance floor separating it from Familiar), and Adventurous used
`depth_for(0.85)` ≈ rank 197 of ~8,000 — the *2.5th percentile* of closeness,
not actually far.

## Working definitions

- **Familiar** — very similar sounding. Often the same genre, not required.
- **Bridge** — a real step further in sound than Familiar, genre may or may
  not differ. The gap from Familiar has to be audible, not just "next in line
  that happens to lack a shared genre tag."
- **Adventurous** — clearly further still — genuinely different from the
  seed, but not so far that it stops being a recognisable extension of it
  (see the catalogue's own ceiling below).

## What the catalogue's own decay curve says

Genre agreement@10-per-band and mean distance, by rank band, full 7,994-track
EffNet catalogue, ~200 seeds/band across all 8 genres:

| rank band | agreement | mean distance |
|---|---:|---:|
| 1-10 | 0.62 | 0.240 |
| 11-30 | 0.55 | 0.285 |
| 31-100 | 0.51 | 0.326 |
| 101-300 | 0.45 | 0.376 |
| 301-1000 | 0.33 | 0.448 |
| 1001-3000 | 0.16 | 0.552 |
| 3001-7993 | 0.06 | 0.695 |

Two things this settles. First, ranks 11-30 barely differ from 1-10 — that's
exactly why Bridge glued itself to Familiar before; there's no real separation
until past rank ~30. Second, by rank 3000+ agreement (0.06) falls *below* the
~0.125 random baseline for 8 balanced genres — that's not adventurous, that's
the model actively pointing at opposite-sounding music. Pushing Adventurous
past roughly rank 2000 stops being "further out" and starts being "wrong."

**Starting proposal, to test by ear, not to treat as final:**

- Familiar: rank 1-15
- Bridge: rank 30-150 (the gap from 15-30 is deliberate — a buffer so Bridge
  can't land right next to Familiar)
- Adventurous: rank 500-2000

Change the ranges in the cell below and re-run to try anything else — that's
the point of this notebook.

In [1]:
import sys
sys.path.append("..")

import ast
import tempfile
import os
from pathlib import Path
import numpy as np
import pandas as pd
import essentia.standard as es
import soundfile as sf
from IPython.display import Audio, display

from modeling.data import load_fma
from modeling.effnet_recommender import EffNetRecommender
from modeling.connecting_factors import ConnectingFactors
from modeling.rhythm import audio_path

REPO_ROOT = Path.cwd().parent if Path.cwd().name == "notebooks" else Path.cwd()
pd.set_option("display.max_colwidth", 60)

tracks = load_fma("small")[1]
rec = EffNetRecommender.from_npz(REPO_ROOT / "data" / "effnet_embeddings_full.npz", tracks)
print(f"catalogue: {len(rec.track_ids_)} tracks")

genres_all = tracks[("track", "genres_all")].apply(ast.literal_eval)
genres_lookup = pd.read_csv(REPO_ROOT / "data" / "raw" / "fma_metadata" / "genres.csv", index_col=0)["title"]

cf = ConnectingFactors.build(tracks)


def genre_names(gids):
    return [genres_lookup.get(i, str(i)) for i in gids]

catalogue: 7994 tracks


In [2]:
PREVIEW_SECONDS = 20
TARGET_RMS = 0.08
MAX_GAIN = 4.0


def load_preview(path, seconds=PREVIEW_SECONDS):
    y = es.MonoLoader(filename=str(path), sampleRate=22050)()
    sr = 22050
    skip = min(10.0, 0.1 * len(y) / sr)
    start = int(skip * sr)
    end = min(start + int(seconds * sr), len(y))
    start = max(0, end - int(seconds * sr))
    clip = y[start:end]
    rms = float(np.sqrt(np.mean(clip ** 2))) or 1e-9
    gain = min(TARGET_RMS / rms, MAX_GAIN)
    return np.clip(clip * gain, -1.0, 1.0), sr


def play(path, label_text):
    print(label_text)
    clip, sr = load_preview(path)
    with tempfile.NamedTemporaryFile(suffix=".ogg", delete=False) as f:
        sf.write(f.name, clip, sr, format="OGG", subtype="VORBIS")
        tmp_path = f.name
    try:
        display(Audio(filename=tmp_path))
    finally:
        os.unlink(tmp_path)

## The tunable tier tool

`explore_tiers` takes explicit **rank ranges** for each tier — not "first N
that pass some filter" — so tiers are structurally separated by distance no
matter what connects them. Within the Bridge and Adventurous ranges, it now
*prefers* candidates with at least one connecting factor from
`modeling.connecting_factors` (genre, genre_lineage, era, geography) — falling
back to the plain distance-ranked pool if fewer than `n` connected candidates
exist in that band, so a tight range never comes up empty. Each pick shows
which factor(s) actually connected it, or `[]` if none did (only possible via
the fallback).

In [3]:
def explore_tiers(seed_id=None, seed_vec=None, seed_artist=None,
                   familiar=(0, 15), bridge=(30, 150), adventurous=(500, 2000), n=5,
                   require_connection_for=("Bridge", "Adventurous"), seed=0):
    if seed_vec is None:
        row = rec._position(seed_id)
        seed_vec = rec.embedding_.iloc[[row]]
    distances, idx = rec.index_.kneighbors(seed_vec, n_neighbors=max(adventurous[1] + 1, 50))
    distances, idx = distances[0], idx[0]
    if seed_id is not None:
        distances, idx = distances[1:], idx[1:]
    candidate_ids = rec.track_ids_[idx]

    if seed_artist is not None:
        artists = tracks.loc[candidate_ids, ("artist", "name")].to_numpy()
        keep = artists != seed_artist
        candidate_ids, distances = candidate_ids[keep], distances[keep]

    rng = np.random.default_rng(seed)
    out = {}
    for label, (lo, hi) in [("Familiar", familiar), ("Bridge", bridge), ("Adventurous", adventurous)]:
        hi = min(hi, len(candidate_ids))
        pool_idx = np.arange(lo, hi)

        if label in require_connection_for and seed_id is not None and len(pool_idx):
            connected = [i for i in pool_idx if cf.factors_between(seed_id, candidate_ids[i])]
            pool_for_pick = connected if len(connected) >= n else list(pool_idx)
        else:
            pool_for_pick = list(pool_idx)

        pick = rng.choice(pool_for_pick, size=min(n, len(pool_for_pick)), replace=False) if pool_for_pick else []
        pick = sorted(pick)
        factors = [cf.factors_between(seed_id, candidate_ids[i]) if seed_id is not None else [] for i in pick]
        out[label] = [(candidate_ids[i], distances[i], i + 1, f) for i, f in zip(pick, factors)]
    return out


def show_and_play(seed_path, seed_label, tiers):
    play(seed_path, seed_label)
    for label, items in tiers.items():
        for tid, d, rank, factors in items:
            m = tracks.loc[tid]
            g = genre_names(genres_all.get(tid, []))
            factor_tag = f" via {factors}" if factors else " (no connecting factor -- fallback)"
            play(audio_path(tid),
                 f"{label}  rank={rank}  distance={d:.3f}{factor_tag}  {m[('artist','name')]} — {m[('track','title')]}  "
                 f"[{m[('track','genre_top')]}] {cf.describe(tid)}")

### Round 1: the starting proposal, on the same three catalogue seeds as
notebooks 07/08 — Hip-Hop (coherent), Instrumental (best genre-agreement),
Pop (the incoherent one) — plus the external seed.

One limitation, not a bug: the external seed has no `genres_all`/era/country
of its own (it never went through FMA's metadata pipeline), so connecting
factors can't be computed for it — its Bridge/Adventurous picks fall back to
pure distance ranking every time, tagged "(no connecting factor -- fallback)"
below. That's expected for this seed specifically, not a sign the tool is
broken.

In [4]:
ROUND_SEEDS = [2, 40659, 3538]  # AWOL - Food; Albert Glasser - The Auction 2; Cryptacize - Say You Will

for seed_id in ROUND_SEEDS:
    m = tracks.loc[seed_id]
    tiers = explore_tiers(seed_id=seed_id, seed_artist=m[("artist", "name")])
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}] ===")
    show_and_play(audio_path(seed_id), "SEED", tiers)


=== SEED 2  AWOL — Food  [Hip-Hop] ===
SEED


Familiar  rank=4  distance=0.173 via ['genre', 'geography']  Hi-Rez — The Remedy (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=5  distance=0.180 via ['genre', 'geography']  CM & Tha Silent Partner — What's It All For  [Hip-Hop] 2014, United States


Familiar  rank=7  distance=0.189 via ['genre', 'geography']  Hi-Rez — Throw It Up Ft. BDG (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=8  distance=0.193 via ['genre', 'geography']  DJ Def Chad — The Remedy  [Hip-Hop] 2014, United States


...

Adventurous  rank=949  distance=0.358 via ['geography']  Gorilla Chief — Problems  [Rock] 2015, United States


Adventurous  rank=1356  distance=0.385 via ['genre']  Red Crickets — My Deviance  [Pop] 2016, Finland


Adventurous  rank=1513  distance=0.394 via ['geography']  Vlada Tomova's Balkan Tales — Momche  [International] 2012, United States


Adventurous  rank=1718  distance=0.406 via ['era']  Project 5am — The Librettist  [Electronic] 2009, United Kingdom


Adventurous  rank=1880  distance=0.415 via ['genre', 'era']  Eric & Magill — Grandpa's Pink Wine  [Pop] 2010, Kenya


In [5]:
SEED_PATH = REPO_ROOT / "data" / "raw" / "youtube_tests" / "Y2Mate.is - Elyjah Slaps the Space.mp3"

external = np.load(REPO_ROOT / "data" / "processed" / "essentia_handoff" / "external_effnet_embeddings.npz",
                    allow_pickle=True)
ext_names, ext_platforms, ext_vecs = external["names"], external["platforms"], external["embeddings"]
ext_vecs_u = ext_vecs / np.linalg.norm(ext_vecs, axis=1, keepdims=True)
seed_idx = int(np.flatnonzero(ext_platforms == "seed")[0])
seed_vec_2d = ext_vecs_u[seed_idx].reshape(1, -1)

tiers = explore_tiers(seed_vec=seed_vec_2d)
print("=== SEED — Elyjah Slaps the Space (external) ===")
show_and_play(SEED_PATH, "SEED", tiers)

=== SEED — Elyjah Slaps the Space (external) ===
SEED


Familiar  rank=4  distance=0.218 (no connecting factor -- fallback)  Josh Spacek — Loaded  [Instrumental] United States


Familiar  rank=5  distance=0.218 (no connecting factor -- fallback)  Malaventura — Let's the kids play  [Pop] Spain


Familiar  rank=7  distance=0.227 (no connecting factor -- fallback)  Blue Ducks — Floss Suffers From Gamma Radiation  [Hip-Hop] (no era/geography data)


Familiar  rank=8  distance=0.246 (no connecting factor -- fallback)  ZOE.LEELA — Bridges  [Pop] 2009


...

Adventurous  rank=916  distance=0.494 (no connecting factor -- fallback)  Ryan Cullinane — Upside Of Looking Down  [Instrumental] (no era/geography data)


Adventurous  rank=1338  distance=0.525 (no connecting factor -- fallback)  DJ Spooky — Arctic Rhythms (Dubstep Mix)  [Electronic] 2013, United States


Adventurous  rank=1507  distance=0.537 (no connecting factor -- fallback)  C-Doc — Far Gone (Featuring DJ Def Chad) (Vocal)  [Hip-Hop] 2012


Adventurous  rank=1723  distance=0.549 (no connecting factor -- fallback)  Langax — Adrenaline Intro  [Electronic] 2016, Spain


Adventurous  rank=1900  distance=0.561 (no connecting factor -- fallback)  Pranavibes — Dream & Bass  [Instrumental] 2016, France

### Round 2 — change the numbers here and re-run

Nudge `familiar` / `bridge` / `adventurous` below (they're `(low_rank,
high_rank)` pairs, 0-based) based on what round 1 sounded like, then re-run
this cell. Repeat until the three tiers feel right; whatever lands here is
what should go into the actual product code.

In [6]:
familiar = (0, 15)
bridge = (30, 150)
adventurous = (500, 2000)

for seed_id in ROUND_SEEDS:
    m = tracks.loc[seed_id]
    tiers = explore_tiers(seed_id=seed_id, seed_artist=m[("artist", "name")],
                           familiar=familiar, bridge=bridge, adventurous=adventurous)
    print(f"\n=== SEED {seed_id}  {m[('artist','name')]} — {m[('track','title')]}  [{m[('track','genre_top')]}] ===")
    show_and_play(audio_path(seed_id), "SEED", tiers)

tiers = explore_tiers(seed_vec=seed_vec_2d, familiar=familiar, bridge=bridge, adventurous=adventurous)
print("\n=== SEED — Elyjah Slaps the Space (external) ===")
show_and_play(SEED_PATH, "SEED", tiers)


=== SEED 2  AWOL — Food  [Hip-Hop] ===
SEED


Familiar  rank=4  distance=0.173 via ['genre', 'geography']  Hi-Rez — The Remedy (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=5  distance=0.180 via ['genre', 'geography']  CM & Tha Silent Partner — What's It All For  [Hip-Hop] 2014, United States


Familiar  rank=7  distance=0.189 via ['genre', 'geography']  Hi-Rez — Throw It Up Ft. BDG (Prod. Joel Johnston)  [Hip-Hop] 2012, United States


Familiar  rank=8  distance=0.193 via ['genre', 'geography']  DJ Def Chad — The Remedy  [Hip-Hop] 2014, United States


...

Adventurous  rank=916  distance=0.494 (no connecting factor -- fallback)  Ryan Cullinane — Upside Of Looking Down  [Instrumental] (no era/geography data)


Adventurous  rank=1338  distance=0.525 (no connecting factor -- fallback)  DJ Spooky — Arctic Rhythms (Dubstep Mix)  [Electronic] 2013, United States


Adventurous  rank=1507  distance=0.537 (no connecting factor -- fallback)  C-Doc — Far Gone (Featuring DJ Def Chad) (Vocal)  [Hip-Hop] 2012


Adventurous  rank=1723  distance=0.549 (no connecting factor -- fallback)  Langax — Adrenaline Intro  [Electronic] 2016, Spain


Adventurous  rank=1900  distance=0.561 (no connecting factor -- fallback)  Pranavibes — Dream & Bass  [Instrumental] 2016, France
